In this lab, we will build a model to perform segmentation of RNA molecules, seen as surfaces.

![](https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/rna_image.png)

For this, we will first build a network able to process these surfaces, and then train it on the dataset.
We will additionnally try some small variations and check their effects.

# Environment and data

Let's download the dataset and additional necessary packages.

You will need a GPU for this Lab. We recommend to use Google Colab.

In [1]:
from google.colab import drive
drive.mount('/content/drive')

Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).


In [2]:
import pathlib

target_dir = pathlib.Path("/content/drive/MyDrive/td4")
target_dir.mkdir(parents=True, exist_ok=True)

target_dir

PosixPath('/content/drive/MyDrive/td4')

In [ ]:
# import urllib.request

# url1 = "https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/RNADataset.zip"
# url2 = "https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/material_TD3.zip"

# path1 = target_dir / "RNADataset.zip"
# path2 = target_dir / "material_TD3.zip"

# urllib.request.urlretrieve(url1, path1)
# urllib.request.urlretrieve(url2, path2)

# print("Files downloaded to:", target_dir)

In [ ]:
# import zipfile

# path1 = target_dir / "RNADataset.zip"
# with zipfile.ZipFile(path1, 'r') as z:
#     z.extractall(target_dir)

# # with zipfile.ZipFile(path2, 'r') as z:
# #     z.extractall(target_dir / "material_TD3")

# # print("Extraction complete!")

In [3]:
import sys, os

sys.path.insert(0, str(target_dir))
os.chdir(target_dir)

print("cwd:", os.getcwd())

cwd: /content/drive/MyDrive/td4


In [4]:
!pip install potpourri3d
!pip install git+https://github.com/skoch9/meshplot.git
# !pip install pythreejs

  Cloning https://github.com/skoch9/meshplot.git to /tmp/pip-req-build-ij0vp5xz
  Running command git clone --filter=blob:none --quiet https://github.com/skoch9/meshplot.git /tmp/pip-req-build-ij0vp5xz
  Resolved https://github.com/skoch9/meshplot.git to commit 725e4a7926a5f10888f0edd1762fecf9db751c56
  Preparing metadata (setup.py) ... done


In [5]:
!pip install -U meshplot pythreejs ipywidgets traitlets

In [ ]:
# !pip install potpourri3d
# !pip install git+https://github.com/skoch9/meshplot.git
# !pip install pythreejs

# !wget https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/RNADataset.zip
# !wget https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/material_TD3.zip

In [ ]:
# !unzip -qq RNADataset
# !unzip -qq material_TD3.zip

Code for colab

In [6]:
!pwd
!ls
%cd /content/drive/MyDrive/td4

import sys
sys.path.append("material_TD3")

/content/drive/MyDrive/td4
__MACOSX  material_TD3	material_TD3.zip  models  RNADataset  RNADataset.zip
/content


In [7]:
from google.colab import output
output.enable_custom_widget_manager()

import os

import torch
import torch.nn as nn

import diffusion_utils

# Part I - Implementing Diffusion DiffusionNet

## Goal

In this assignment we will focus on building [DiffusionNet](https://arxiv.org/pdf/2012.00888.pdf), which was presented during the lecture.
This network uses differential geometry tools to compute per-vertex features which can later be used for several tasks such as classification, segmentation or matching.

Recall that the DiffusionNet architechture can be visualized as follows :

![](https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/TD3/DiffusionNet.PNG)


Therefore, following this image, we will build the following objects using PyTorch:
1. **Precomputed operators**. Most of them have been introduced in TD1, the gradient matrix is provided in the `diffusion_utils.py` file provided with this TD (do not modify it!).
2. **Spatial Diffusion**. Using again TD1 (part on spectral diffusion).
3. **Spatial Gradient features**. Using gradient matrices
4. **Per-vertex MLP**. Basic PyTorch
5. **DiffusionNet block** and **DiffusionNet** which consists in assembling the previous 4 parts.

## Reminders on PyTorch
[Pytorch](https://pytorch.org/docs/stable/index.html) is a standard library to build and train neural networks. Two essential components are auto-differentiation and GPU support with parallelization of operations.

A [`torch.Tensor`](https://pytorch.org/docs/stable/tensors.html) object is very similar to a `numpy.array`, and most existing operations in numpy have identical equivalent in PyTorch. However behaviors can be slightly different so always check the documentation ! Using built-in PyTorch functions instead of numpy enables automatic gradient computation.

Note that PyTorch operations are built to be significantly accelerated on GPU by using parallel computing. This implies that the first dimension of a `torch.Tensor` is most often interpreted as the batch dimension and operations are applied *in parallel* to each element of the batch **independently**.
For instance, given a tensor `A` of size `[M,N]` and a tensor `X` of size `[B,N,P]`, the output of `A @ X` will be of size `[B,M,P]`, where the matrix multiplication by `A` is applied to each of the `X[i]` in parallel.

In DiffusionNet, some blocks (*eg* the diffusion block) can be applied to multiple surfaces in parallel so batches are made of surfaces. On the contrary the MLP or gradient features blocks are applied to each vertex independantly so the batches are made of vertices. This will require some particular care when coding.

## 1 - Implementing Diffusion Net

In this section, we seek to implement a version of DiffusionNet which only handles oriented triangle meshes.

It will be impossible for you to test that the output of the functions are the right ones before the complete pipeline is built. However, since shapes are provided in the description of each function, you can ensure each module outputs a tensor of the right shape.

## 1.1 - Some utils

We here code 2 utility functions used in the diffusion block, which allow to project  (resp. unproject) functions to (resp. from) the spectral basis **taking the batch dimension** into account.

For simplicity, we use a batch size = $1$ in this TD as it's tricky to combine functions defined on a mesh with $n_1$ vertices with functions defined on another mesh with $n_2$ vertices.


**Projection**: Recall from TD1, that given functions on a mesh stored in a matrix $\mathbf{f}\in\mathbb{R}^{n\times p}$, the projection into the spectral basis of size $K$ can be done via the matrix multiplication $\Phi^\top A \mathbf{f}$, where $\Phi\in\mathbb{R}^{n\times K}$ are the eigenvectors of the laplacian of the shape and A the area matrix of the shape.

**Reverse projection**: Recall from TD1, that given spectral coefficients of functions on a mesh stored in a matrix $\alpha\in\mathbb{R}^{K\times p}$, the corresponding functions on the mesh are defined as $\Phi \alpha \in\mathbb{R}^{n\times p}$.

### Question 1
**Compute the projection and reverse projection functions, which take batch of functions**

**Tips**:
1. If `A` is to torch Tensor of shape `(B,N,M)`, then `A.mT` does batch-wise matrix transpose and has shape `(B,M,N)`
2. Given a diagonal matrix $A$ and a function $f\in\mathbb{R}^n$, then $Af = \left(A_{ii}f_i\right)$, where $A_{ii}$ are the diagonal values of $A$ (vertex areas in our case). We therefore directly use the diagonal values as input.
3. For matrix multiplication, multiple operations are possibly, namely torch.mm, torch.einsum or the traditional @ operator. Choose what you understand the most easily.


In [8]:
def project_to_basis(x, evecs, vertex_areas):
    """
    Project an input sinal x to the spectral basis.


    Parameters
    -------------------
    x            : (B, n, p) Tensor of input
    evecs        : (B, n, K) Tensor of eigenvectors
    vertex_areas : (B, n,) vertex areax

    Output
    -------------------
    projected_values : (B, K, p) Tensor of coefficients in the basis
    """
    phi_A = evecs * vertex_areas[:, :, None] # (B, n, K)
    return torch.einsum("bnk,bnp->bkp", phi_A, x) ## TODO



def unproject_from_basis(coeffs, evecs):
    """
    Transform input coefficients in basis into a signal on the complete shape.

    Parameters
    -------------------
    coefs : (B, K, p) Tensor of coefficients in the spectral basis
    evecs : (B, n, K) Tensor of eigenvectors

    Output
    -------------------
    decoded_values : (B, n, p) values on each vertex
    """
    return torch.einsum("bnk,bkp->bnp", evecs, coeffs) ## TODO

## 1.2 - Spectral Diffusion module

The DiffusionModule in Diffusion takes as input a mesh $M$ and set of functions $\left(f_1,\dots, f_p\right)$  on the mesh - that is $f_j:M\to\mathbb{R}$ - and outputs $\left(g_1,\dots, g_p\right)$ with $g_j:M\to\mathbb{R}$ and where $g_j$ the the **diffused version** of $f_j$ after time $t_j$.

Note that each feature function $f_j$ is diffused for time $t_j$ where the time parameter **depends on the index of the function**.
DiffusionNet proposes to **learn each time parameter** $t_1,\dots, t_p$. There is therefore $p$ learnable parameters in this module.


In order to compute Diffusion efficiently, we will use the spectral diffusion approximation introduced in TD1.

Recall from that TD1 that the Laplacian eigenvectors of a mesh made of $N$ vertices can stored in a matrix $\Phi\in\mathbb{R}^{N\times K}$.
Given an initial function $f_0$, its (spectral) diffused version $f_t$ after time $t$ can be written $f_t = \Phi \alpha_t$ with
$$
(\alpha_t)_j = \exp(-t\lambda_j)\beta_j
$$

where $\beta=\Phi^\top A f_0 \ \in\mathbb{R}^K$ is the projection of $f_0$ in the basis, and $A$ the diagonal area matrix.

### Question 2
**Fill the SpectralDiffusion module which diffuses features with learnable time parameters.**

**Clue:**
1. Use [`nn.Parameter`](https://pytorch.org/docs/stable/generated/torch.nn.parameter.Parameter.html) to create learnable parameters in a module
2. Use [`nn.init.constant_`](https://pytorch.org/docs/stable/nn.init.html#torch.nn.init.constant_) to initialize time parameters to 0
3. Be careful about the dimension of inputs, outputs, intermediate tensors, ...

In [9]:
class SpectralDiffusion(nn.Module):

    def __init__(self, n_channels):
        """
        Initializes the module with time parameters to 0.

        Parameters
        ------------------
        n_channels : int - number of input feature functions
        """
        # This runs the __init__ function of nn.Module
        super().__init__()

        self.n_channels = n_channels

        ## TODO DEFINE AND INITIALIZE THE Diffusion times as learnable parameters.
        self.diffusion_times = nn.Parameter(torch.zeros(n_channels), requires_grad=True)


    def forward(self, x, evals, evecs, vertex_areas):
        """
        Given input features x and information on the current meshes
        return diffused versions of the features.

        Parameters
        ------------------------
        x     : (B, n, p) batch of input features. p = self.n_channels
        evals : (B, K,) batch of eigenvalues
        evecs : (B, n, K) batch of eigenvectors
        vertex_areas : (B, n,) batch of vertex areax


        Output
        ------------------------
        x_diffuse : diffused version of each input feature
        """
        # Remove negative diffusion times
        with torch.no_grad():
            self.diffusion_times.data = torch.clamp(self.diffusion_times, min=1e-8)

        ## TODO DIFFUSE x
        beta = project_to_basis(x, evecs, vertex_areas) # (B, K, p)
        alfa = torch.exp(-torch.einsum("bk,p->bkp", evals, self.diffusion_times)) * beta
        x_diffused = unproject_from_basis(alfa, evecs)

        return x_diffused

## 1.3 Gradient Features module

The gradient feature module allows to compute features from the gradient of the diffused feature. This module treats **each vertex independantly**. The batch size is here the number of vertices and not the shape as a whole.

This modules takes as input **the gradient of each feature** at a vertex, and outputs **a real number for each feature** for this vertex.


The gradient of the features is a **vector field**, so a pair of numbers at each vertex. In practice, the value at a vertex $v$ is stored as a complex number $z\in\mathbb{C}^n$. Because there are $p$ different features for each vertex, we concatenate the $p$ gradients (one for each feature) and obtain a per-vertex vector field $w_v\in\mathbb{C}^{p}$ as **input**.

The gradient feature module therefore takes a vertex embedding $w_v$ as input and outputs a *real-valued* embedding $g_v\in\mathbb{R}^{p}$ where

$$
g_v = \tanh\left(\langle w_v, B w_v\rangle_{\mathbb{C}}\right)
$$
with $\tanh$ and $\langle\rangle_{\mathbb{C}}$ applied **element-wise**.


Where $B$ is a **complex and learnable** matrix, and $\langle\rangle_{\mathbb{C}}$ can be seen as the $\mathbb{R}^2$ inner product when identifying $\mathbb{C}$ with $\mathbb{R}^2$. This means for $a,b,c,d\in\mathbb{R}$ that:
$$
\langle a+ib, c+id\rangle_{\mathbb{C}} = ac + bd
$$


In summary, the gradient feature module:
 - Takes $w_v\in\mathbb{C}^{p}$ as input
 - Computes $g_v$ using the formula above
 - Has $B\in\mathbb{C}^p$ as a unique parameter

### Question 3
**Implement the Gradient Feature Module**

**Tips**:

1. In practice, use $w_v\in\mathbb{R}^{p\times 2}$ and $B=B_{re}+iB_{im}$ where both matrix are real values $p\times p$ matrices. Compute separately the real and imaginary part of $Bw_v$, then apply the inner product and hyperbolic tangent element-wise.
2. A learnable matrix multipication can be represented as a [`nn.Linear`](https://pytorch.org/docs/stable/generated/torch.nn.Linear.html) layer

In [10]:
class SpatialGradient(nn.Module):
    """
    Module which computes g_v from vertex embeddings.
    """
    def __init__(self, n_channels):
        """
        Initializes the module.

        Parameters
        ------------------
        n_channels : int - number of input feature functions
        """

        super().__init__()

        self.n_channels = n_channels

        # Real and Imaginary part of B
        self.B_re = nn.Linear(self.n_channels, self.n_channels, bias=False)
        self.B_im = nn.Linear(self.n_channels, self.n_channels, bias=False)

    def forward(self, vects):
        """
        Parameters
        ----------------------
        Vects : (N, P, 2) per-vertex vector field (w_v)

        Output
        ---------------------
        features : (N, P) per-vertex scalar field
        """
        vects_re = vects[...,0]  # (N,P) real part of w_v
        vects_im = vects[...,1]  # (N,P) imaginary part of w_v

        ## TODO Perform forward pass

        # (a+bi)*(c+di)= (ac-bd) + i(ad+bc); a=B_re, b=B_im, c=vects_re, d=vects_im
        mult_re = self.B_re(vects_re) - self.B_im(vects_im)
        mult_im = self.B_re(vects_im) + self.B_im(vects_re)
        inner_p = vects_re*mult_re + vects_im*mult_im
        return torch.tanh(inner_p)


## 1.4 MLP module

The MLP module is a simple multi-layer perceptron which acts on **each vertex independantly**.

This can be customizable using custom hidden layer sizes and droupout.

### Question 4
**Code the MiniMLP module (with dropout and activation)**

**Tip**:
1. Activation is not applied to the last layer
2. Given a list `layer_list` of `torch.nn` modules, one can generate a large layer using `nn.Sequential(*layer_list)`. See the [documentation](https://pytorch.org/docs/stable/generated/torch.nn.Sequential.html) for more info
3. Batch is made of per-vertex embedding, not per surface.

In [11]:
class MiniMLP(nn.Sequential):
    '''
    A simple MLP with activation and potential dropout
    '''
    def __init__(self, layer_sizes, dropout=False, activation=nn.ReLU):
        """
        Activation and dropout is applied after all layer BUT the last one

        Parameters
        ---------------------------
        layer_size : list of ints - list of sizes of the MLP
        dropout    : book - whether to add droupout or not
        activation : nn.module : activation function
        """
        super().__init__()

        layer_list = []

        ## TODO FILL THE LAYER LIST
        for i in range(len(layer_sizes)-1):
          in_features, out_features = layer_sizes[i], layer_sizes[i+1]
          layer_list.append(nn.Linear(in_features, out_features))

          if i < len(layer_sizes)-2: # apply the activation and dropout after all but last layer
            layer_list.append(activation())
            if dropout:
              layer_list.append(nn.Dropout())

        self.layer = nn.Sequential(*layer_list)

    def forward(self, x):
        """
        Parameters
        --------------------
        x : (n, p) - input features, batch size is the number of vertices !

        Output
        -------------------
        y : (n,p') - output features
        """
        # NOTHING TO DO HERE
        return self.layer(x)

## 1.5 DiffusionNet Block

![](https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/TD3/DiffusionNet.PNG)

Each diffusion block contains 3 main modules which were implemented in the preceeding three questions. Namely, (1) Learned spectral diffusion, (2) Gradient Feature module and (3) Point-wise features from the MLP module applied sequentially.

Note the following points:
1. Input and output are per-vertex scalars
2. The width (or number of features) is the same as input and output
3. The Diffusion module uses the input features as input.
4. The Spatial Gradient module uses the **gradient** of the output of the Diffusion module as input
5. The MiniMLP uses the **concatenation** of the input features, the output of the Diffusion module and the output of the Spatial Gradient module as input. Its input size is 3 times the number of features.
6. The input features are **added** to the output using a **residual connection**.


### Question 5

**Assemble the Diffusion + Gradient + MLP modules to construct diffusion block using the image and explanation above**

**Tip**
 - We pre-filled the code to compute the gradient of the features
 - We only provide the size of the **hidden** layers of the MLP. You must add the input and output dimension.

In [12]:
class DiffusionNetBlock(nn.Module):
    """
    Complete Diffusion block
    """

    def __init__(self, n_channels, dropout=True, use_diffusion=True, use_gradient=True):
        """
        Initializes the module.

        Parameters
        ------------------
        n_channels      : int - number of feature functions (serves as both input and output)
        mlp_hidden_dims : list of int - sizes of HIDDEN layers of the miniMLP.
                          You should add the input and output dimension to it.
        use_diffusion: bool - flag determining should the diffusion layer be used (Q8) (default: True)
        use_gradient : bool - flag determining should the gradient layer be used (Q8) (default: True)
        """
        super(DiffusionNetBlock, self).__init__()

        # Specified dimensions
        self.n_channels = n_channels
        self.dropout = dropout
        # Q8 flags
        self.use_diffusion = use_diffusion
        self.use_gradient = use_gradient

        # Diffusion block
        # TODO DEFINE THE 3 SUBPARTS
        self.spectral_diffusion = SpectralDiffusion(n_channels) if use_diffusion else None
        self.spatial_gradient = SpatialGradient(n_channels) if use_gradient else None

        # if all three modules are used, the first MLP layer is of size 3*n_channels
        # else changed dinamically according to Q8 flags
        mlp_in_channels = n_channels + int(use_diffusion*n_channels) + int(use_gradient*n_channels)
        self.mini_mlp = MiniMLP([mlp_in_channels, n_channels, n_channels, n_channels], dropout=dropout)


    def forward(self, x_in, vertex_areas, evals, evecs, gradX, gradY):
        """
        Parameters
        -------------------
        x_in         : (B,n,p) - Tensor of input signal.
        vertex_areas : (B,n) - Tensor of vertex areas
        evals        : (B, K,) batch of eigenvalues
        evecs        : (B, n, K) batch of eigenvectors
        gradX        : Half of gradient matrix, sparse real tensor with dimension [B,N,N]
        gradY        : Half of gradient matrix, sparse real tensor with dimension [B,N,N]

        Output
        -------------------
        x_out : (B,n,p) - Tensor of output signal.
        """

        # Manage dimensions
        B = x_in.shape[0] # batch dimension

        feats = [] # aggregate features for input to mini_mlp
        feats.append(x_in) # x_in is always present

        # Diffusion block
        if self.use_diffusion: # if diffusion module is used, get diffusion features and append them
          x_diffuse = self.spectral_diffusion(x_in, evals, evecs, vertex_areas) # DIFFUSED X_in  # (B, N, p)
          feats.append(x_diffuse)
        else: # if diffusion module is not used, set x_diffuse to x_in and proceed to gradient module
          x_diffuse = x_in

        # if gradient module is used, get gradient features and append them
        # else skip
        if self.use_gradient:
          # Compute the batch of gradients
          x_grads = [] # Manually loop over the batch
          for b in range(B):
              # gradient after diffusion
              x_gradX = torch.mm(gradX[b,...], x_diffuse[b,...])
              x_gradY = torch.mm(gradY[b,...], x_diffuse[b,...])

              x_grads.append(torch.stack((x_gradX, x_gradY), dim=-1))

          x_grad = torch.stack(x_grads, dim=0)  # (B, N, P, 2)

          # TODO EVALUATE GRADIENT FEATURES
          x_grad_feats = self.spatial_gradient(x_grad)
          feats.append(x_grad_feats)

        # TODO APPLY THE MLP TO THE CONCATENATED FEATURES
        cat_feats = torch.cat(feats, dim=-1)
        mlp_feats = self.mini_mlp(cat_feats)

        # TODO APPLY THE RESIDUAL CONNECTION

        return x_in + mlp_feats

## 1.6 - DiffusionNet

Let's check again the architecture:
![](https://www.lix.polytechnique.fr/Labo/Robin.Magnet/INF631/TD3/DiffusionNet.PNG)

DiffusionNet takes as input per-vertex features of size $p_{in}$. Is first uses a linear layer to transform theses features into $p$-dimensional features, where $p$ is the width of DiffusionNet. There are then multiple blocks of DiffusionNetBlock to produce new features. Similarly to input features, a last linear layer transforms the $p$ dimensional features into vertex features of size $p_{out}$

### Question 6

**Build the DiffusionNet. It consists of an MLP in the first layer to reac with `N_block` of `DiffusionNetBlock` which was implemented in the previous cell.**

In [13]:
class DiffusionNet(nn.Module):

    def __init__(self, p_in, p_out, n_channels=128, N_block=4, last_activation=None, mlp_hidden_dims=None, dropout=True, use_diffusion=True, use_gradient=True):
        """
        Construct a DiffusionNet.
        Parameters
        --------------------
        p_in            : int - input dimension of the network
        p_out           : int - output dimension  of the network
        n_channels      : int - dimension of internal DiffusionNet blocks (default: 128)
        N_block         : int - number of DiffusionNet blocks (default: 4)
        last_activation : int - a function to apply to the final outputs of the network, such as torch.nn.functional.log_softmax
        mlp_hidden_dims : list of int - a list of hidden layer sizes for MLPs (default: [C_width, C_width])
        dropout         : bool - if True, internal MLPs use dropout (default: True)
        use_diffusion: bool - flag determining should the diffusion layer be used (Q8) (default: True)
        use_gradient : bool - flag determining should the gradient layer be used (Q8) (default: True)
        """

        super(DiffusionNet, self).__init__()

        ## Store parameters

        # Basic parameters
        self.p_in = p_in
        self.p_out = p_out
        self.n_channels = n_channels
        self.N_block = N_block

        # Outputs
        self.last_activation = last_activation # we do not use it because of the loss choice

        # MLP options
        # not used
        if mlp_hidden_dims == None:
            mlp_hidden_dims = [n_channels, n_channels]
        self.mlp_hidden_dims = mlp_hidden_dims
        self.dropout = dropout

        # Q8 flags
        self.use_diffusion = use_diffusion
        self.use_gradient = use_gradient


        ## TODO SETUP THE NETWORK (LINEAR LAYERS + BLOCKS)

        self.blocks = [] # TOFILL
        self.blocks.append(nn.Linear(p_in, n_channels)) # define input linear layer
        for i in range(N_block):
          self.blocks.append(DiffusionNetBlock(n_channels, dropout=dropout, use_diffusion=use_diffusion, use_gradient=use_gradient)) # add N_block diffusion blocks
        self.blocks.append(nn.Linear(n_channels, p_out)) # define output linear layer
        self.net = nn.ModuleList(self.blocks) # you can then access each block by self.net[i]


    def forward(self, x_in, vertex_areas, evals=None, evecs=None, gradX=None, gradY=None):
        """
        Progapate a signal through the network.
        Can handle input without batch dimension (will add a dummy dimension to set batch size to 1)

        Parameters
        --------------------
        x_in         : (n,p) or (B,n,p) - Tensor of input signal.
        vertex_areas : (n,) or (B,n) - Tensor of vertex areas
        evals        : (B, K,) or (K,) batch of eigenvalues
        evecs        : (B, n, K) or (n, K) batch of eigenvectors
        gradX        : Half of gradient matrix, sparse real tensor with dimension [N,N] or [B,N,N]
        gradY        : Half of gradient matrix, sparse real tensor with dimension [N,N] or [B,N,N]

        Output
        -----------------------
        x_out (tensor):    Output with dimension [N,C_out] or [B,N,C_out]
        """


        ## Check dimensions, and append batch dimension if not given
        if x_in.shape[-1] != self.p_in:
            raise ValueError(f"DiffusionNet was constructed with p_in={self.p_in}, "
                             f"but x_in has last dim={x_in.shape[-1]}")
        N = x_in.shape[-2]

        if len(x_in.shape) == 2:
            appended_batch_dim = True

            # add a batch dim to all inputs
            x_in = x_in.unsqueeze(0) # (B, N, P)
            vertex_areas = vertex_areas.unsqueeze(0) # (B, N)
            if evals != None: evals = evals.unsqueeze(0) # (B,K)
            if evecs != None: evecs = evecs.unsqueeze(0) # (B,N,K)
            if gradX != None: gradX = gradX.unsqueeze(0) # (B,N,N)
            if gradY != None: gradY = gradY.unsqueeze(0) # (B,N,N)

        elif len(x_in.shape) == 3:
            appended_batch_dim = False

        else: raise ValueError("x_in should be tensor with shape (n,p) or (B,n,p)")

        ##  TODO PROCESS THE INPUTS
        in_linear, diffusion_blocks, out_linear = self.net[0], self.net[1:-1], self.net[-1] # parse the network
        x_out = in_linear(x_in)
        for diffusion_block in diffusion_blocks:
          x_out = diffusion_block(x_out, vertex_areas, evals, evecs, gradX, gradY)
        x_out = out_linear(x_out)

        # Remove batch dim if we added it
        if appended_batch_dim:
            x_out = x_out.squeeze(0) # (N, p_out)

        return x_out

# Part II - RNA segmentation.

**Given meshes of the molecular envelopes for RNA molecules, gathered from the PDB database, we will be segementing them. That is, each vertex is assigned a ground-truth segmentation label according to ~120 functional categories. See [1] for more details. We use this data as a representative task for 3D machine learning on surfaces, predicting the functional segmentation from only the molecule surface shape using DiffusionNet.**


[1] https://hal.inria.fr/hal-02167454v2/document

## 1. Visualize the data

Here is some code to visualize the training data with segmentation of the surfaces.

In [14]:
from rna_dataset import RNAMeshDataset
from mesh_utils.mesh import TriMesh
import matplotlib.pyplot as plt
import plot_utils as plu

In [15]:

root_dir = './RNADataset/'

train_dataset = RNAMeshDataset(root_dir, train=True, num_eig=128, op_cache_dir=None)

loading 60 files: ['5JUO_D.off', '5T62_B.off', '4WCE_Y.off', '4V9K_BB.off', '5E81_16.off', '3J92_7.off', '4V7X_BB.off', '5T7V_C.off', '4TUE_RB.off', '5DGE_3.off', '4V7B_BB.off', '4U4O_3.off', '3JA1_LB.off', '3PIO_Y.off', '5EL7_16.off', '5MDY_3.off', '5H5U_B.off', '4U4O_7.off', '5TBW_AS.off', '5J30_RB.off', '4W4G_RB.off', '4V7J_AB.off', '4V8J_BB.off', '2OTJ_9.off', '4V7X_DB.off', '3J9Y_B.off', '1VQK_9.off', '1Q82_B.off', '4W2H_DB.off', '3G4S_9.off', '1NKW_9.off', '4V5J_BB.off', '3JBN_AB.off', '4V8E_CB.off', '4YZV_YB.off', '4V9P_CB.off', '5J5B_DB.off', '4U6F_7.off', '5OBM_7.off', '3JCD_B.off', '4V55_BA.off', '5IBB_16.off', '1VY7_BB.off', '5GAD_B.off', '4U4Q_3.off', '4WRA_1J.off', '5ADY_A.off', '4V70_BB.off', '4TUB_RB.off', '5AJ0_A4.off', '1KD1_B.off', '4V6N_AA.off', '4V8I_BB.off', '4W4G_YB.off', '4V8F_DB.off', '4V8P_E3.off', '4V5Y_BA.off', '4TUA_YB.off', '5DFE_RB.off', '4V5K_DB.off']


In [16]:
# This loads all operators

data1 = train_dataset[19]
mesh1 = TriMesh(data1['vertices'].numpy(), data1["faces"].numpy())

data2 = train_dataset[37]
mesh2 = TriMesh(data2['vertices'].numpy(), data2["faces"].numpy())


## You can see what kind of information is provided
print(data1.keys())

/content/drive/MyDrive/td4/material_TD3/diffusion_utils.py:196: RuntimeWarning: invalid value encountered in divide
  vertex_normals = vertex_normals / np.linalg.norm(vertex_normals,axis=-1,keepdims=True)
/content/drive/MyDrive/td4/material_TD3/diffusion_utils.py:365: UserWarning: torch.sparse.SparseTensor(indices, values, shape, *, device=) is deprecated.  Please use torch.sparse_coo_tensor(indices, values, shape, dtype=, device=). (Triggered internally at /pytorch/torch/csrc/utils/tensor_new.cpp:653.)
  return torch.sparse.FloatTensor(torch.LongTensor(indices), torch.FloatTensor(values), torch.Size(shape)).coalesce()


dict_keys(['vertices', 'faces', 'frames', 'vertex_area', 'L', 'evals', 'evecs', 'gradX', 'gradY', 'labels', 'labels_og'])


In [19]:
cmap1 = plt.get_cmap("jet")(data1["labels"].numpy() / (train_dataset.n_classes-1))[:,:3]
cmap2 = plt.get_cmap("jet")(data2["labels"].numpy() / (train_dataset.n_classes-1))[:,:3]

plu.plot(mesh1, cmap1)
# plu.plot(mesh2, cmap2)

Renderer(camera=PerspectiveCamera(children=(DirectionalLight(color='white', intensity=0.6, position=(0.1324982…

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_8e43860a-ac2e-40e3-8d83-5e6d0ec3c86c'.

### Load training and validation dataset

All operators and eigenfunctions are precomputed and saved in a cache folder. Computing the cache can take a few minutes.

If you are using colab, you might want first to mount your drive and save the cache there (You can change the `op_cache_dir`) so that you don't have to recompute it everytime. Or either compute the cache once, download it and upload it again everytime. This might be faster than recomputing all along.

To access your google drive, use this code:


```
from google.colab import drive
drive.mount('/content/drive')
```

This makes your Drive available at `/content/drive/My Drive/`

In [21]:
# WARNING: Do not change this cell

from rna_dataset import RNAMeshDataset
from torch.utils.data import DataLoader

root_dir = './RNADataset/'
op_cache_dir = './RNADataset/cache'
num_eig = 128

train_dataset = RNAMeshDataset(root_dir, train=True, num_eig=num_eig, op_cache_dir=op_cache_dir)
train_loader = DataLoader(train_dataset, batch_size=None, shuffle=True, num_workers=0, persistent_workers=False)

valid_dataset = RNAMeshDataset(root_dir, train=False, num_eig=num_eig, op_cache_dir=op_cache_dir)
valid_loader = DataLoader(valid_dataset, batch_size=None, num_workers=0, persistent_workers=False, )

loading 60 files: ['5JUO_D.off', '5T62_B.off', '4WCE_Y.off', '4V9K_BB.off', '5E81_16.off', '3J92_7.off', '4V7X_BB.off', '5T7V_C.off', '4TUE_RB.off', '5DGE_3.off', '4V7B_BB.off', '4U4O_3.off', '3JA1_LB.off', '3PIO_Y.off', '5EL7_16.off', '5MDY_3.off', '5H5U_B.off', '4U4O_7.off', '5TBW_AS.off', '5J30_RB.off', '4W4G_RB.off', '4V7J_AB.off', '4V8J_BB.off', '2OTJ_9.off', '4V7X_DB.off', '3J9Y_B.off', '1VQK_9.off', '1Q82_B.off', '4W2H_DB.off', '3G4S_9.off', '1NKW_9.off', '4V5J_BB.off', '3JBN_AB.off', '4V8E_CB.off', '4YZV_YB.off', '4V9P_CB.off', '5J5B_DB.off', '4U6F_7.off', '5OBM_7.off', '3JCD_B.off', '4V55_BA.off', '5IBB_16.off', '1VY7_BB.off', '5GAD_B.off', '4U4Q_3.off', '4WRA_1J.off', '5ADY_A.off', '4V70_BB.off', '4TUB_RB.off', '5AJ0_A4.off', '1KD1_B.off', '4V6N_AA.off', '4V8I_BB.off', '4W4G_YB.off', '4V8F_DB.off', '4V8P_E3.off', '4V5Y_BA.off', '4TUA_YB.off', '5DFE_RB.off', '4V5K_DB.off']


get_all_operators:   0%|          | 0/60 [00:00<?, ?it/s]

loading 13 files: ['4V83_BB.off', '1VQ6_9.off', '4V7K_BB.off', '4V9A_DB.off', '3JQ4_B.off', '5KCS_1B.off', '4LT8_RB.off', '4V56_BA.off', '1N8R_B.off', '4V4I_x.off', '5FDV_2B.off', '4V57_BA.off', '4V9Q_CB.off']


get_all_operators:   0%|          | 0/13 [00:00<?, ?it/s]

## 2 -  Training the network

##  <font color='red'>Requirement: we need you to save the model weights and send it with the notebook to be evaluated on this question. Otherwise, this question will not reward points</font>

In order to easily run multiple experiments, we will use a class `Trainer` to run the complete training and testing code.

This way we can simply change parameters as arguments when building the class and run the training easily.

### Question 7: Fill the trainer class

This function is mostly pre-filled. Here are the parts you should implement yourself:

1. In the `__init__` function, **build DiffusionNet** using the `model_cfg` dictionary you will provide as input. An example of model config is the following:

```python
model_cfg = {'inp_feat': 'xyz',  # Type of input Features (xyz, HKS, WKS)
              'num_eig': 32,  # Number of eigenfunctions to use for Spectral Diffusion
              'p_in': 3,  # Number of input features
              'p_out': train_dataset.n_classes,  # Number of output features
              'N_block': 4,  # Number of DiffusionNetBlock
              'n_channels': 128}  # Width of the network
```

2. In the `__init__` function, **define the loss**. Note that segmentation is essentially multi-label classification. The number of classes is given by `train_dataset.n_classes`.

3. Fill in the `forward_step` `train_epoch`, `valid_epoch` methods. Note this is pretty simple and depends on your choice of loss / activation function combination.



In [37]:
# You can remove prints if you want
from tqdm.notebook import tqdm
import numpy as np
import os

class Trainer(object):

    def __init__(self, diffusionnet_cls, model_cfg, train_loader, valid_loader, device='cuda',
                 lr=1e-3, weight_decay=1e-4, num_epochs=200,
                 lr_decay_every = 50, lr_decay_rate = 0.5,
                 log_interval=10, save_dir=None, model_name=None):

        """
        diffusionnet_cls: (nn.Module) class of the DiffusionNet model
        model_cfg: (dict) keyword arguments for model
        train_loader: (torch.utils.DataLoader) DataLoader for training set
        valid_loader: (torch.utils.DataLoader) DataLoader for validation set
        device: (str) 'cuda' or 'cpu'
        lr: (float) learning rate
        weight_decay: (float) weight decay for optimiser
        num_epochs: (int) number of epochs
        lr_decay_every: (int) decay learning rate every this many epochs
        lr_decay_rate: (float) decay learning rate by this factor
        log_interval: (int) print training stats every this many iterations
        save_dir: (str) directory to save model checkpoints
        model_name: (str) name of model to save
        """

        # TODO build the network from the model_cfg

        self.model = diffusionnet_cls(
                        model_cfg["p_in"],
                        model_cfg["p_out"],
                        model_cfg["n_channels"],
                        model_cfg["N_block"],
                        dropout = model_cfg["dropout"],
                        use_diffusion = model_cfg["use_diffusion"],
                        use_gradient = model_cfg["use_gradient"]
                    )

        # loss for segmentation
        self.loss = nn.CrossEntropyLoss() ## USE A MEANINGFUL LOSS



        ## THIS PART JUST STORES SOME OTHER PARAMETERS
        self.train_loader = train_loader
        self.valid_loader = valid_loader
        self.device = device
        self.lr = lr
        self.weight_decay = weight_decay
        self.num_epochs = num_epochs

        self.optimizer = torch.optim.Adam(self.model.parameters(), lr=self.lr, weight_decay=self.weight_decay)


        self.lr_decay_every = lr_decay_every
        self.lr_decay_rate = lr_decay_rate
        self.log_interval = log_interval
        self.save_dir = save_dir
        self.model_name = model_name

        self.train_losses = []
        self.test_losses = []
        self.train_accs = []
        self.test_accs = []

        self.inp_feat = model_cfg.get('inp_feat', 'xyz')
        self.num_eig = model_cfg.get('num_eig', 128)
        if not self.inp_feat in ['xyz', 'hks', 'wks']:
            raise ValueError('inp_feat must be one of xyz, hks, wks')

        self.model.to(self.device)


    def forward_step(self, verts, faces, frames, vertex_area, L, evals, evecs, gradX, gradY):
        """
        Perform a forward step of the model.

        Args:
            verts (torch.Tensor): (N, 3) tensor of vertex positions
            faces (torch.Tensor): (F, 3) tensor of face indices
            frames (torch.Tensor): (N, 3, 3) tensor of tangent frames.
            vertex_area (torch.Tensor): (N, N) sparse Tensor of vertex areas.
            L (torch.Tensor): (N, N) sparse Tensor of cotangent Laplacian.
            evals (torch.Tensor): (num_eig,) tensor of eigenvalues.
            evecs (torch.Tensor): (N, num_eig) tensor of eigenvectors.
            gradX (torch.Tensor): (N, N) tensor of gradient in X direction.
            gradY (torch.Tensor): (N, N) tensor of gradient in Y direction.

        Returns:
            pred (torch.Tensor): (N, p_out) tensor of predicted labels.
        """

        if self.inp_feat == 'xyz':
            features = verts
        elif self.inp_feat == 'hks':
            features = self.compute_HKS(evecs, evals, self.num_eig, n_feat=32)
        elif self.inp_feat == 'wks':
            features = self.compute_WKS(evecs, evals, self.num_eig, n_feat=32) # changed num_E (originally written) to n_feat

        preds = self.model(features, vertex_area, evals=evals, evecs=evecs, gradX=gradX, gradY=gradY)

        # MAYBE ADD ACTIVATION TODO
        return preds



    def train_epoch(self):
        """
        Train the network for one epoch
        """
        train_loss = 0
        train_acc = 0
        for i, batch in enumerate(tqdm(self.train_loader, "Train epoch")):

            verts = batch["vertices"].to(self.device)
            faces = batch["faces"].to(self.device)
            frames = batch["frames"].to(self.device)
            vertex_area = batch["vertex_area"].to(self.device)
            L = batch["L"].to(self.device)
            evals = batch["evals"].to(self.device)
            evecs = batch["evecs"].to(self.device)
            gradX = batch["gradX"].to(self.device)
            gradY = batch["gradY"].to(self.device)
            labels = batch["labels"].to(self.device)

            self.optimizer.zero_grad()

            preds = self.forward_step(verts, faces, frames, vertex_area, L, evals, evecs, gradX, gradY)
            # MAYBE DO SOMETHING TO THE PREDS

            # COMPUTE THE LOSS
            loss = self.loss(preds, labels) #TODO

            loss.backward()
            self.optimizer.step()

            train_loss += loss.item()

            # COMPUTE TRAINING ACCURACY
            pred_labels = torch.argmax(preds, dim=-1) # TODO GET PREDICTED LABELS

            n_correct = pred_labels.eq(labels).sum().item() # number of correct predictions
            train_acc += n_correct/labels.shape[0]

        return train_loss/len(self.train_loader), train_acc/len(self.train_loader)

    def valid_epoch(self):
        """
        Run a validation epoch
        """
        val_loss = 0
        val_acc = 0
        print("Start val epoch")
        for i, batch in enumerate(self.valid_loader):

            # READ BATCH
            verts = batch["vertices"].to(self.device)
            faces = batch["faces"].to(self.device)
            frames = batch["frames"].to(self.device)
            vertex_area = batch["vertex_area"].to(self.device)
            L = batch["L"].to(self.device)
            evals = batch["evals"].to(self.device)
            evecs = batch["evecs"].to(self.device)
            gradX = batch["gradX"].to(self.device)
            gradY = batch["gradY"].to(self.device)
            labels = batch["labels"].to(self.device)

            # TODO PERFORM FORWARD STEP
            preds = self.forward_step(verts, faces, frames, vertex_area, L, evals, evecs, gradX, gradY)
            # MAYBE DO SOMETHING TO THE PREDS

            # Compute Loss - THIS DEPENDS ON YOUR CHOICE OF LOSS
            loss = self.loss(preds, labels) ##


            val_loss += loss.item()

            # Compute ACCURACCY
            pred_labels = torch.argmax(preds, dim=-1) ## TODO

            n_correct = pred_labels.eq(labels).sum().item() # number of correct predictions
            val_acc += n_correct/labels.shape[0]
        print("End val epoch")
        return val_loss/len(self.valid_loader), val_acc/len(self.valid_loader)

    def evaluate(self):
        """
        Run evaluation after the training
        """
        self.model.eval()

        accuracy = 0
        for i, batch in enumerate(self.valid_loader):

            # READ BATCH
            verts = batch["vertices"].to(self.device)
            faces = batch["faces"].to(self.device)
            frames = batch["frames"].to(self.device)
            vertex_area = batch["vertex_area"].to(self.device)
            L = batch["L"].to(self.device)
            evals = batch["evals"].to(self.device)
            evecs = batch["evecs"].to(self.device)
            gradX = batch["gradX"].to(self.device)
            gradY = batch["gradY"].to(self.device)
            labels = batch["labels"].to(self.device)

            preds = self.forward_step(verts, faces, frames, vertex_area, L, evals, evecs, gradX, gradY)
            pred_labels = torch.argmax(preds, dim=-1)

            n_correct = pred_labels.eq(labels).sum().item() # number of correct predictions
            accuracy += n_correct/labels.shape[0]

        return accuracy/len(self.valid_loader)

    def run(self):
        os.makedirs('./models', exist_ok=True)
        for epoch in range(self.num_epochs):
            self.model.train()

            if epoch % self.lr_decay_every == 0:
                self.adjust_lr()

            train_ep_loss, train_ep_acc = self.train_epoch()
            self.train_losses.append(train_ep_loss)
            self.train_accs.append(train_ep_acc)

            if epoch % self.log_interval == 0 or epoch == 0:
                val_loss, val_acc = self.valid_epoch()
                torch.save(self.model.state_dict(), os.path.join(self.save_dir, 'model_latest_hks.pth'))
                print(f'Epoch: {epoch:03d}/{self.num_epochs}, '
                      f'Train Loss: {train_ep_loss:.4f}, '
                      f'Train Acc: {1e2*train_ep_acc:.2f}%, '
                      f'Val Loss: {val_loss:.4f}, '
                      f'Val Acc: {1e2*val_acc:.2f}%')
        os.makedirs(self.save_dir, exist_ok=True) # added code for creating the dir
        torch.save(self.model.state_dict(), os.path.join(self.save_dir, f'{self.model_name}.pth'))


    def visualize(self):
        """
        We only test the first two shapes of validation set.
        """
        self.model.eval()
        test_seg_meshes = []

        for i, batch in enumerate(self.valid_loader):
            verts = batch["vertices"].to(self.device)
            faces = batch["faces"].to(self.device)
            frames = batch["frames"].to(self.device)
            vertex_area = batch["vertex_area"].to(self.device)
            L = batch["L"].to(self.device)
            evals = batch["evals"].to(self.device)
            evecs = batch["evecs"].to(self.device)
            gradX = batch["gradX"].to(self.device)
            gradY = batch["gradY"].to(self.device)
            labels = batch["labels"].to(self.device)


            preds = self.forward_step(verts, faces, frames, vertex_area, L, evals, evecs, gradX, gradY)
            pred_labels = torch.max(preds, dim=1).indices

            test_seg_meshes.append([TriMesh(verts.cpu().numpy(), faces.cpu().numpy()),
                                  pred_labels.cpu().numpy()])
            if i==1:
                break


        cmap1 = plt.get_cmap("jet")(test_seg_meshes[0][-1] / (146))[:,:3]
        cmap2 = plt.get_cmap("jet")(test_seg_meshes[1][-1] / (146))[:,:3]

        plu.double_plot(test_seg_meshes[0][0], test_seg_meshes[1][0], cmap1, cmap2)
        #return plot_multi_meshes(test_seg_meshes, cmap='vert_colors')

    def adjust_lr(self):
        lr = self.lr * self.lr_decay_rate
        for param_group in self.optimizer.param_groups:
            param_group['lr'] = lr

    def compute_HKS(self, evecs, evals, num_eig, n_feat):
        """
        Compute the HKS features for each vertex in the mesh.
        Args:
            evecs (torch.Tensor): (N, K) tensor of eigenvectors
            evals (torch.Tensor): (K,) tensor of eigenvectors
            num_eig (int): number of eigenvalues to use
            n_feat (int): number of features to compute

        Returns:
            hks (torch.Tensor): (N, n_feat) tensor of HKS features
        """
        # code has been adapted since it didn't compile due to a mix of numpy and tensor variables and functions
        abs_ev = torch.sort(torch.abs(evals)).values[:num_eig]

        t_list = np.geomspace(4*np.log(10)/abs_ev[-1].item(), 4*np.log(10)/abs_ev[1].item(), n_feat)
        t_list = torch.from_numpy(t_list.astype(np.float32)).to(device=evecs.device)

        evals_s = abs_ev

        coefs = torch.exp(-t_list[:,None] * evals_s[None,:])  # (num_T,K)

        natural_HKS = torch.einsum('tk,nk->nt', coefs, evecs[:,:num_eig].square())

        inv_scaling = coefs.sum(1)  # (num_T)

        return (1/inv_scaling)[None,:] * natural_HKS

    def compute_WKS(self, evecs, evals, num_eig, n_feat):
        """
        Compute the WKS features for each vertex in the mesh.

        Args:
            evecs (torch.Tensor): (N, K) tensor of eigenvectors
            evals (torch.Tensor): (K,) tensor of eigenvectors
            num_eig (int): number of eigenvalues to use
            n_feat (int): number of features to compute

        Returns:
            wks: torch.Tensor: (N, num_E) tensor of WKS features
        """
        # code has been adapted since it didn't compile due to a mix of numpy and tensor variables and functions
        abs_ev = torch.sort(torch.abs(evals)).values[:num_eig]

        e_min,e_max = np.log(abs_ev[1].item()),np.log(abs_ev[-1].item())
        sigma = 7*(e_max-e_min)/n_feat

        e_min += 2*sigma
        e_max -= 2*sigma

        energy_list = torch.linspace(e_min,e_max,n_feat,device=evecs.device)

        evals_s = abs_ev

        coefs = torch.exp(-torch.square(energy_list[:,None] - torch.log(torch.abs(evals_s))[None,:])/(2*sigma**2))  # (num_E,K)

        natural_WKS = torch.einsum('tk,nk->nt', coefs, evecs[:,:num_eig].square())

        inv_scaling = coefs.sum(1)  # (num_E)
        return (1/inv_scaling)[None,:] * natural_WKS



### Training and visualising segmentation results.

Simply execute the next two cells. There are no TODOs.

We will define a function (for a better code readability) that builds the configuration dictionary for the model. Function supports the configuration for the base model and all the other models from Question 8.
The following models are supported (and will later be evaluated):
- 'base': Uses xyz coordinates as input features (3 input features).  Uses both diffusion and gradient modules.
- 'no_diff': Same as 'base' model, but doesn't use diffusion module.
- 'no_grad': Same as 'base' model, but doesn't use gradient module.
- 'hks': Uses hks descriptors as input features (32 input features). Uses both diffusion and gradient modules.
- 'wks': Uses wks descriptors as input features (32 input features). Uses both diffusion and gradient modules.


In [24]:
def get_config(model_type="base", verbose=False):
  cfg = {
        'inp_feat': None, # updated below based on model_type
        'num_eig': 32,
        'p_in': None,        # updated below based on inp_feat
        'p_out': train_dataset.n_classes,
        'N_block': 4,
        'n_channels': 128,
        'dropout': True,
        'use_diffusion': True, # by default, diffusion module is used
        'use_gradient': True, # by default, gradient module is used
    }

  if model_type not in ["base", "no_diff", "no_grad", "hks", "wks"]:
      raise ValueError(f"Model type has to be one of: base/no_diff/no_grad/hks/wks.")

  # change input features
  if model_type == "base" or model_type == "no_diff" or model_type == "no_grad":
      cfg['inp_feat'] = "xyz"
  elif model_type == "hks":
      cfg['inp_feat'] = "hks"
  elif model_type == "wks":
      cfg['inp_feat'] = "wks"

  # change the use of diffusion or gradient
  if model_type == "no_diff":
      cfg['use_diffusion'] = False
  elif model_type == "no_grad":
      cfg['use_gradient'] = False

  # change p_in parameter based on inp_feat
  # xyz have 3 features, while hks and wks have 32 features
  match cfg['inp_feat']:
      case 'xyz': cfg['p_in'] = 3
      case 'hks': cfg['p_in'] = 32
      case 'wks': cfg['p_in'] = 32

  if verbose:
    print(cfg)

  return cfg

In [ ]:
# Let's define the trainer
model_cfg = get_config(model_type="base")
my_trainer = Trainer(DiffusionNet,  model_cfg, train_loader, valid_loader, device=torch.device("cuda"), save_dir='./models', model_name="base_200_epochs", num_epochs = 200)
#my_trainer.run()

# Let's visualize the predicted segmentation at initialization
my_trainer.visualize()

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_236a6bc6-6851-4ce0-9a8a-91860a6163b3'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_740f5562-af98-4db8-b65e-44dda5332ea9'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_05b459ce-95c0-4331-8fe9-acda5ee71c01'.

In [ ]:
# We can now run the training. IT should take some time (around 2-3 hours). Do not close Colab during the training!
my_trainer.run()

# And visualize (it's supposed to be clean!)
my_trainer.visualize()

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Start val epoch
End val epoch
Epoch: 000/200, Train Loss: 4.8327, Train Acc: 1.51%, Val Loss: 4.6724, Val Acc: 2.45%


Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

...

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_671ab82f-62ef-4838-aedd-d4b97e42965f'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_35955a9c-ff49-42ef-8fb7-efbfb10e5f15'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_2b56fbab-0a05-42ec-b758-9bba711c6087'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_e4b13b14-8d54-4199-8627-4f515c78929c'.

### Question 8: Ablation studies

#### This is the final question of this lab which involves several subquestions. The objective is to understand the utility of different components of DiffusionNet block built during this session. More specifically, we will make one change at a time to the above network to understand how the segmentation accuracy varies.


1. Remove the learned diffusion module such that a "Diffusion" block consists of MLP + Gradient features.

2. Remove the Gradient feature module such that a "Diffusion" block consists of Diffusion + MLP features.

3. Instead of feeding in the `xyz` coordinate as features, what happens if either of HKS and/or WKS is used as a feature?


The first two question consists of reimplementing `DiffusionNet` module such that it incorporates aforementioned changes into the blocks. Either create a new class or add arguments which you'll use in the `model_cfg` dictionary.

For the last question, please pay attention to `inp_feat` and `p_in`.

We will evaluate every model from Question 8 (details about the models are provided in of one of the cells from Question 7).

In [ ]:
### TODO:
no_diff_model_cfg = get_config(model_type="no_diff")
no_diff_trainer = Trainer(DiffusionNet, no_diff_model_cfg, train_loader, valid_loader, device=torch.device("cuda"), save_dir='./models', model_name="no_diff_200_epochs", num_epochs=200)
no_diff_trainer.run()

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Start val epoch
End val epoch
Epoch: 000/200, Train Loss: 4.8904, Train Acc: 1.26%, Val Loss: 4.7919, Val Acc: 1.71%


Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

...

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

In [ ]:
no_diff_trainer.visualize()

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_e01ff5ba-6f38-497a-bad4-e644a6486649'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_78ffe264-c656-433c-8c04-00397f243279'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_0e3017f1-ab0a-41be-b47c-a9ff29db737a'.

In [ ]:
no_grad_model_cfg = get_config(model_type="no_grad")
no_grad_trainer = Trainer(DiffusionNet, no_grad_model_cfg, train_loader, valid_loader, device=torch.device("cuda"), save_dir='./models', model_name="no_grad_200_epochs", num_epochs=200)
no_grad_trainer.run()

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Start val epoch
End val epoch
Epoch: 000/200, Train Loss: 4.8408, Train Acc: 1.48%, Val Loss: 4.7117, Val Acc: 2.34%


Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

...

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

In [ ]:
no_grad_trainer.visualize()

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_965ae427-4042-4a7e-8f41-9e2b7fd15bf5'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_c3c317d6-e213-4029-aad6-dc4a5479125f'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_b07ce15e-952c-41dd-bc0a-0af212d36120'.

In [ ]:
hks_model_cfg = get_config("hks")
hks_trainer = Trainer(DiffusionNet, hks_model_cfg, train_loader, valid_loader, device=torch.device("cuda"), save_dir='./models', model_name="hks_200_epochs", num_epochs=200)
hks_trainer.run()

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Start val epoch
End val epoch
Epoch: 000/200, Train Loss: 4.8461, Train Acc: 1.61%, Val Loss: 4.5208, Val Acc: 2.35%


Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

...

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

In [ ]:
hks_trainer.visualize()

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_10087dae-6455-4802-adbb-c2359f1cd436'.

TraitError: The 'target' trait of a DirectionalLight instance expected an Uninitialized or an Object3D, not the str 'IPY_MODEL_2b48ed42-ba19-48a9-a063-672129653ca6'.

In [ ]:
wks_model_cfg = get_config(model_type="wks")
wks_trainer = Trainer(DiffusionNet, wks_model_cfg, train_loader, valid_loader, device=torch.device("cuda"), save_dir='./models', model_name="wks_200_epochs", num_epochs=200)
wks_trainer.run()

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Start val epoch
End val epoch
Epoch: 000/200, Train Loss: 4.7204, Train Acc: 2.54%, Val Loss: 4.4247, Val Acc: 5.01%


Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

...

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

Train epoch:   0%|          | 0/60 [00:00<?, ?it/s]

We now evaluate all model variants from Question 8:

In [45]:
device = torch.device("cuda") if torch.cuda.is_available() else 'cpu'
model_full_names = ["Base", "No diffusion module", "No gradient module", "HKS features", "WKS features"]
for i, model_type in enumerate(["base", "no_diff", "no_grad", "hks", "wks"]):
  cfg = get_config(model_type=model_type)
  model_path = f"./models/{model_type}_200_epochs.pth"
  state_dict = torch.load(model_path, map_location=device)

  trainer = Trainer(DiffusionNet, cfg, train_loader, valid_loader, device=device)
  trainer.model.load_state_dict(state_dict)
  trainer.model.to(device)
  trainer.model.eval()

  accuracy = trainer.evaluate()
  print(f"Model: {model_full_names[i]} | Accuracy: {round(accuracy*100,2)}%")

Model: Base | Accuracy: 80.64%
Model: No diffusion module | Accuracy: 32.28%
Model: No gradient module | Accuracy: 64.0%
Model: HKS features | Accuracy: 79.05%
Model: WKS features | Accuracy: 78.98%


### Discussion

**No diffusion module model**: We first observe a large drop in accuracy when the diffusion module is removed. Learned diffusion features are responsible for low-frequency communication across points on the surface [1]. Without them, the model relies only on MLP layers and gradient features, which provide only local information. As a consequence, the network loses the ability to propagate information globally and thus loses global context. The decrease in performance confirms that diffusion is the most crucial component of this architecture.

**No gradient module model**: Accuracy is again reduced compared to the base model, but much less than in the previous case. Gradient features are responsible for learning the high-frequency components needed for the task-e.g., segmentation [1]. Without them, the model is still able to learn from diffusion features, yet it loses the ability to capture directional and anisotropic variations in the features which consequently leads to lower accuracy.

**HKS and WKS input feature models**: Using HKS or WKS instead of xyz features results in small accuracy drop. Moreover, the accuracy between these two models is nearly the same. HKS and WKS features are used to make the network invariant to isometric deformations and therefore used when higher invariance is desired. However, our results show that the network can learn equally well from all three types of input features. This suggests that the intrinsic nature of diffusion and gradients already provides high geometric robustness of the network [1]. Consequently, the performance gap between different input features is minor. In addition, our comparative results match the results reported in [1] on the same segmentation task, which further confirms that the choice of input features has only a small impact on performance (on this specific task).

References:  
[1] Sharp, N., Attaiki, S., Crane, K., & Ovsjanikov, M. (2020). Diffusion is All You Need for Learning on Surfaces. arXiv:2012.00888.